# Chord play-along video
Generate full-length MP4s from original audio and your saved Hann-window HMM CSVs, without retraining.

The standard video shows the current chord, next chord countdown, full-song waveform and moving red playhead. An optional second **evaluation MP4** compares predictions with cleaned original-pitch ground truth: black = correct, red = incorrect, with the correct chord in smaller text beside it. Unannotated time is marked and excluded from accuracy.

Run steps 1–5 in order. Choose your run in step 2 and song in step 3. Outputs are saved to `full_data/playalong_videos`.


## 1. Install and connect Drive
MoviePy 2 is pinned because its API differs from many older tutorials. Installation and rendering require a connected Colab runtime. Grant Drive access when prompted.


In [1]:
%pip -q install moviepy==2.2.1 pillow numpy pandas soundfile matplotlib

from pathlib import Path
import json
import re
import shutil
import tempfile
import numpy as np
import pandas as pd
import soundfile as sf
from PIL import Image, ImageDraw, ImageFont
from moviepy import AudioFileClip, VideoClip
from IPython.display import display, Video
from google.colab import drive

drive.mount("/content/drive")
project_path = Path("/content/drive/MyDrive/Femman/DT2470 Music Informatics/DT2470 Project/full_data")
results_path = project_path / "aam_window_hmm_results"
audio_folder = project_path / "0001-1000-audio-mixes"
output_folder = project_path / "playalong_videos"
assert project_path.is_dir(), f"Edit project_path: {project_path}"


   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 129.9/129.9 kB 3.6 MB/s eta 0:00:00
Mounted at /content/drive


## 2. Find exported prediction runs
Run this cell to list the export folders. With multiple runs, set `run_number` and rerun this cell. The initial choice is the most recently modified manifest/folder; verify the printed path and model settings.

The manifest is optional. If it is missing, folders containing `*_predictions.csv` are still listed. Paths are resolved relative to your current project so moving the whole project folder works.


In [2]:
manifests = list((results_path / "evaluation").rglob("playback_manifest.json"))
run_folders = {p.parent for p in manifests}
run_folders.update(p.parent for p in (results_path / "evaluation").rglob("*_predictions.csv"))
def run_modified(folder):
    marker = folder / "playback_manifest.json"
    return (marker if marker.exists() else folder).stat().st_mtime
runs = sorted(run_folders, key=run_modified, reverse=True)
if not runs:
    raise FileNotFoundError("No exported test CSVs. Check results_path or export predictions in the HMM notebook.")
for i, folder in enumerate(runs):
    print(i, folder)

run_number = 0  # Change this if you want another exported run.
prediction_folder = runs[run_number]
manifest_path = prediction_folder / "playback_manifest.json"
manifest = json.loads(manifest_path.read_text()) if manifest_path.exists() else {}
print("Selected:", prediction_folder)
print("Model settings:", manifest.get("config", "not recorded"))


0 /content/drive/MyDrive/Femman/DT2470 Music Informatics/DT2470 Project/full_data/aam_window_hmm_results/evaluation/4f12560a1fd5a9f6
1 /content/drive/MyDrive/Femman/DT2470 Music Informatics/DT2470 Project/full_data/aam_window_hmm_results/evaluation/5d8614f2af458d59
2 /content/drive/MyDrive/Femman/DT2470 Music Informatics/DT2470 Project/full_data/aam_window_hmm_results/evaluation/633da64eb09c4de1
3 /content/drive/MyDrive/Femman/DT2470 Music Informatics/DT2470 Project/full_data/aam_window_hmm_results/evaluation/ec1c1e08f454963c
Selected: /content/drive/MyDrive/Femman/DT2470 Music Informatics/DT2470 Project/full_data/aam_window_hmm_results/evaluation/4f12560a1fd5a9f6
Model settings: {'method': 'stft', 'window_ms': 200, 'overlap': 0.25}


## 3. Match test CSVs to original audio
Choose `song_id` after inspecting the list. Only exported prediction files are used. If duplicate audio matches exist, set `audio_override` to the exact file you want. For WAV/FLAC, waveform reading uses SoundFile; other supported formats use MoviePy/FFmpeg.

For your own song, you can instead set both overrides to its audio and prediction CSV.


In [7]:
prediction_files = {p.name.removesuffix("_predictions.csv"): p
                    for p in prediction_folder.glob("*_predictions.csv")}
audio_index = {}
for path in audio_folder.rglob("*"):
    match = re.fullmatch(r"(\d{4})_mix\.(flac|wav|mp3|m4a|ogg)", path.name, re.IGNORECASE)
    if match and path.is_file():
        audio_index.setdefault(match.group(1), []).append(path)
print("Exported songs:", ", ".join(sorted(prediction_files)))

song_id = sorted(prediction_files)[10]  # Example: "0174" (must be in the exported list).
audio_override = None  # Or Path("/content/drive/MyDrive/my_song.wav")
csv_override = None    # Or Path("/content/drive/MyDrive/my_song_window_chords.csv")

csv_path = Path(csv_override) if csv_override else prediction_files[song_id]
if audio_override:
    audio_path = Path(audio_override)
else:
    candidates = audio_index.get(song_id, [])
    recorded = manifest.get("audio_files", {}).get(song_id)
    if not candidates and recorded and Path(recorded).is_file():
        candidates = [Path(recorded)]
    if len(candidates) != 1:
        raise ValueError(f"Expected one original mix for {song_id}; found {candidates}. Set audio_override.")
    audio_path = candidates[0]
assert audio_path.is_file() and csv_path.is_file(), "Check the selected paths."
print("Audio:", audio_path)
print("Chords:", csv_path)
display(pd.read_csv(csv_path).head())


Exported songs: 0001, 0003, 0007, 0010, 0011, 0031, 0040, 0042, 0045, 0050, 0057, 0060, 0061, 0066, 0067, 0070, 0071, 0073, 0074, 0078, 0080, 0082, 0083, 0085, 0087, 0089, 0098, 0108, 0110, 0111, 0119, 0132, 0133, 0134, 0137, 0140, 0146, 0149, 0169, 0173, 0174, 0185, 0193, 0200, 0210, 0211, 0212, 0214, 0216, 0219, 0229, 0236, 0238, 0239, 0245, 0248, 0255, 0257, 0260, 0261, 0266, 0275, 0276, 0278, 0281, 0282, 0290, 0292, 0295, 0297, 0306, 0308, 0313, 0315, 0317, 0319, 0320, 0324, 0328, 0333, 0334, 0343, 0347, 0351, 0352, 0353, 0360, 0363, 0364, 0372, 0378, 0383, 0406, 0409, 0429, 0430, 0431, 0441, 0449, 0451, 0463, 0466, 0478, 0479, 0482, 0483, 0495, 0496, 0500, 0501, 0502, 0514, 0522, 0523, 0524, 0528, 0529, 0531, 0535, 0537, 0544, 0548, 0560, 0576, 0577, 0581, 0584, 0585, 0588, 0589, 0590, 0591, 0614, 0618, 0627, 0630, 0632, 0636, 0644, 0651, 0653, 0657, 0661, 0663, 0669, 0671, 0679, 0688, 0690, 0696, 0698, 0706, 0707, 0709, 0714, 0718, 0723, 0742, 0746, 0758, 0762, 0765, 0778, 0788, 

,time_s,bar,quarter,chord,end_time_s,next_chord,next_time_s
0,0.000000,NaN,NaN,Amin,2.775420,Fmaj,2.775420
1,2.775420,NaN,NaN,Fmaj,4.125624,Cmaj,4.125624
2,4.125624,NaN,NaN,Cmaj,5.475828,Fmaj,5.475828
3,5.475828,NaN,NaN,Fmaj,8.176236,Emin,8.176236
4,8.176236,NaN,NaN,Emin,10.876644,Gmaj,10.876644


## 4. Video generator
Default: **full audio duration, 1280 × 720, 30 fps**. The waveform uses smoothed amplitude bars with rounded ends and a blue playback fill.

`make_playalong(audio_path, csv_path, output_path)` makes a standard video. Pass `ground_truth_path=...` for an evaluation video.

CSV intervals are read and adjacent identical chords are merged for display. Gaps show no prediction. `N` displays as No chord. The original soundtrack is preserved. After the final prediction, the audio continues without extending a chord.

Evaluation uses the cleaned reference's original-pitch chords. It compares labels at the current playback time, so a reference change can change the color mid-prediction. Accuracy is exact correctly predicted **annotated duration / total annotated duration**, including N; missing predictions are incorrect. Reference gaps and the audio tail are excluded. This is calculated from the selected CSV and shown next to the song name. It is not onset F1 or an unweighted average of rows. Enharmonic spellings such as C# and Db compare as equal.

The ground truth is read only for the optional evaluation video. Rendering does not change the prediction CSV or model metrics.


In [8]:
def load_video_font(size, bold=False):
    # Matplotlib ships its own fonts, independent of Colab's system font paths.
    from matplotlib import font_manager
    try:
        properties = font_manager.FontProperties(family="DejaVu Sans", weight="bold" if bold else "normal")
        path = font_manager.findfont(properties)
        return ImageFont.truetype(path, size)
    except (OSError, ValueError):
        return ImageFont.load_default(size=size)


def read_chords(csv_path):
    table = pd.read_csv(csv_path).rename(columns={"start": "time_s", "start_time_s": "time_s", "end": "end_time_s"})
    required = ["time_s", "end_time_s", "chord"]
    if not set(required).issubset(table.columns):
        raise ValueError(f"CSV needs {required}")
    table = table[required].copy()
    for column in required[:2]:
        table[column] = pd.to_numeric(table[column], errors="raise")
    if table.empty or table.chord.isna().any():
        raise ValueError("CSV is empty or has missing chords.")
    table.chord = table.chord.astype(str).str.strip()
    table = table.sort_values("time_s").reset_index(drop=True)
    bounds = table[["time_s", "end_time_s"]].to_numpy()
    if not np.isfinite(bounds).all() or (bounds[:, 0] < 0).any() or (bounds[:, 1] <= bounds[:, 0]).any():
        raise ValueError("Invalid chord interval times.")
    if (bounds[1:, 0] < bounds[:-1, 1] - 1e-7).any():
        raise ValueError("Overlapping chord intervals; check the CSV.")
    rows = []
    for start, end, chord in table.itertuples(index=False, name=None):
        if rows and chord == rows[-1][2] and abs(start - rows[-1][1]) < 1e-7:
            rows[-1][1] = end
        else:
            rows.append([start, end, chord])
    return pd.DataFrame(rows, columns=required)


def pretty_chord(chord):
    return "No chord" if chord.lower() in {"n", "nc", "n.c."} else chord.replace(":", "")


def chord_status(t, starts, ends, chords):
    i = np.searchsorted(starts, t, side="right") - 1
    if i >= 0 and t < ends[i]:
        current = pretty_chord(chords[i])
        upcoming = i + 1
    else:
        current = "End of chord predictions" if t >= ends[-1] else "No chord prediction"
        upcoming = np.searchsorted(starts, t, side="right")
    if upcoming < len(starts):
        seconds = max(0.0, starts[upcoming] - t)
        # Round upward so the countdown never says 0.0 s before the change.
        countdown = np.ceil(seconds * 10) / 10
        next_text = f"Next: {pretty_chord(chords[upcoming])} in {countdown:.1f} s"
    else:
        next_text = "No upcoming chord"
    return current, next_text


def canonical_chord(value):
    value = str(value).strip().replace(":", "").replace("_", "")
    if value.lower() in {"n", "nc", "n.c.", "none"}:
        return "N"
    match = re.fullmatch(r"([A-G])([#b]?)(maj|min|m|M)?", value)
    if not match:
        raise ValueError(f"Unsupported chord label: {value}")
    root, accidental, quality = match.groups()
    pitch = {"C": 0, "D": 2, "E": 4, "F": 5, "G": 7, "A": 9, "B": 11}[root]
    pitch = (pitch + {"": 0, "#": 1, "b": -1}[accidental]) % 12
    return f"{pitch}:{'min' if quality in {'min', 'm'} else 'maj'}"


def read_reference(path):
    table = pd.read_csv(path)
    if "original_chord" in table:
        table["chord"] = table.original_chord
    elif "transpose_semitones" in table and "chord_C" not in table:
        if not table.transpose_semitones.eq(0).all():
            raise ValueError("Evaluation needs original-pitch reference chords, not C-transposed chords.")
    return read_chords_table(table)


def read_chords_table(table):
    # Reuse interval validation without modifying the supplied CSV.
    with tempfile.TemporaryDirectory() as folder:
        path = Path(folder) / "reference.csv"
        table.to_csv(path, index=False)
        return read_chords(path)


def reference_at(t, reference):
    i = np.searchsorted(reference.time_s.to_numpy(), t, side="right") - 1
    if i >= 0 and t < reference.end_time_s.iloc[i]:
        return reference.chord.iloc[i]
    return None


def annotated_accuracy(prediction, reference, duration):
    # Exact duration overlap, including reference N intervals. Reference gaps and
    # the unannotated audio tail are excluded; uncovered reference time is wrong.
    correct = total = 0.0
    pstart = prediction.time_s.to_numpy()
    pend = prediction.end_time_s.to_numpy()
    plabels = [canonical_chord(c) for c in prediction.chord]
    for start, end, chord in reference.itertuples(index=False, name=None):
        end = min(end, duration)
        if end <= start:
            continue
        total += end - start
        overlap = np.maximum(0, np.minimum(pend, end) - np.maximum(pstart, start))
        correct += overlap[np.array(plabels) == canonical_chord(chord)].sum()
    return correct / total if total else float("nan")


def make_playalong(audio_path, csv_path, output_path, fps=30, size=(1280, 720), preview_seconds=None, ground_truth_path=None):
    audio_path, output_path = Path(audio_path), Path(output_path)
    width, height = size
    if fps <= 0 or min(size) < 320 or width % 2 or height % 2:
        raise ValueError("Use positive fps and even image dimensions of at least 320 pixels.")
    if preview_seconds is not None and preview_seconds <= 0:
        raise ValueError("preview_seconds must be positive.")
    if output_path.suffix.lower() != ".mp4":
        raise ValueError("Output filename must end with .mp4")
    table = read_chords(csv_path)
    starts, ends = table.time_s.to_numpy(), table.end_time_s.to_numpy()
    chords = table.chord.to_numpy()
    reference = read_reference(ground_truth_path) if ground_truth_path else None
    scale = height / 720
    normal = load_video_font(max(12, round(26 * scale)))
    large = load_video_font(max(18, round(84 * scale)), bold=True)
    medium = load_video_font(max(14, round(42 * scale)), bold=True)

    with tempfile.TemporaryDirectory(prefix="playalong_") as work:
        work = Path(work)
        local_audio = work / ("audio" + audio_path.suffix)
        shutil.copyfile(audio_path, local_audio)
        with AudioFileClip(str(local_audio)) as audio:
            full_duration = audio.duration
            accuracy = annotated_accuracy(table, reference, full_duration) if reference is not None else None
            duration = min(full_duration, preview_seconds) if preview_seconds else full_duration
            if ends[-1] > full_duration + 0.1:
                raise ValueError("CSV extends past the audio. Check that the files are the same song.")
            try:
                samples, sr = sf.read(local_audio, dtype="float32", always_2d=True)
                mono = samples.mean(axis=1)
                del samples
            except (RuntimeError, sf.LibsndfileError):
                # Only for drawing; the soundtrack still uses the original file.
                mono = audio.to_soundarray(fps=11025).mean(axis=1)
            if len(mono) == 0:
                raise ValueError("Empty audio.")

            background = Image.new("RGB", size, "#fafbfe")
            draw = ImageDraw.Draw(background)
            left, right = round(width * .06), round(width * .94)
            top, bottom = round(height * .43), round(height * .81)
            middle = (top + bottom) / 2
            draw.rounded_rectangle((left-18*scale, top-20*scale, right+18*scale, bottom+20*scale),
                                   radius=20*scale, fill="white", outline="#edf0f6")
            count = max(1, int((right - left) / (6*scale)))
            edges = np.linspace(0, len(mono), count + 1, dtype=int)
            envelope = []
            for a, b in zip(edges[:-1], edges[1:]):
                block = mono[a:b]
                envelope.append(.55*np.sqrt(np.mean(block**2)) + .45*np.max(np.abs(block)) if len(block) else 0)
            envelope = np.asarray(envelope)
            envelope = np.convolve(np.pad(envelope, (1, 1), mode="edge"), [0.2, 0.6, 0.2], mode="valid")
            envelope = np.clip(envelope / max(float(np.percentile(envelope, 99)), 1e-8), 0, 1)
            played = background.copy()
            played_draw = ImageDraw.Draw(played)
            for j, peak in enumerate(envelope):
                x = left + (j + .5) * (right-left) / count
                amplitude = max(2*scale, peak * (bottom-top) / 2)
                box = (x-1.8*scale, middle-amplitude, x+1.8*scale, middle+amplitude)
                # Rounded, softly varying bars; played bars gain a blue gradient.
                draw.rounded_rectangle(box, radius=1.8*scale, fill="#d8e1ee")
                f = j / max(1, count-1)
                color = (round(56+52*f), round(138-39*f), round(220+12*f))
                played_draw.rounded_rectangle(box, radius=1.8*scale, fill=color)
            title = audio_path.stem[:55]
            if accuracy is not None:
                score = f"{100*accuracy:.2f}%" if np.isfinite(accuracy) else "N/A"
                title += f"  |  Accuracy: {score}"
            draw.text((left, height*.95), title, font=normal, fill="#667085", anchor="lm")

            def centered_text(draw, y, text, font, fill):
                # Fit long gap/end messages without clipping at the edges.
                available = width * .9
                if draw.textlength(text, font=font) > available:
                    font = load_video_font(max(12, int(font.size * available / draw.textlength(text, font=font))), bold=True)
                draw.text((width/2, y), text, font=font, fill=fill, anchor="mm")

            def frame(t):
                image = background.copy()
                draw = ImageDraw.Draw(image)
                current, upcoming = chord_status(t, starts, ends, chords)
                truth = reference_at(t, reference) if reference is not None else None
                active = np.searchsorted(starts, t, side="right") - 1
                has_prediction = active >= 0 and t < ends[active]
                wrong = truth is not None and (not has_prediction or canonical_chord(chords[active]) != canonical_chord(truth))
                if wrong:
                    correction = f"  (correct: {pretty_chord(truth)})"
                    small = load_video_font(max(12, round(28*scale)))
                    main = large
                    combined = draw.textlength(current, font=main) + draw.textlength(correction, font=small)
                    if combined > width*.9:
                        main = load_video_font(max(12, int(main.size*width*.9/combined)), bold=True)
                        small = load_video_font(max(12, int(small.size*width*.9/combined)))
                    combined = draw.textlength(current, font=main) + draw.textlength(correction, font=small)
                    xtext = (width-combined)/2
                    draw.text((xtext, height*.12), current, font=main, fill="#d92d20", anchor="lm")
                    draw.text((xtext+draw.textlength(current, font=main), height*.12), correction,
                              font=small, fill="#667085", anchor="lm")
                else:
                    centered_text(draw, height*.12, current, large, "#111111")
                if reference is not None and truth is None:
                    centered_text(draw, height*.40, "Outside reference annotations", normal, "#98a2b3")
                centered_text(draw, height*.24, "↓", medium, "#999999")
                centered_text(draw, height*.33, upcoming, medium, "#777777")
                x = left + np.clip(t / full_duration, 0, 1) * (right-left)
                # Copy just the waveform region, keeping the chord text and footer.
                crop_box = (left, top, max(left, int(x)), bottom+1)
                if crop_box[2] > left:
                    image.paste(played.crop(crop_box), (left, top))
                draw.line((x, top-10*scale, x, bottom+10*scale), fill="#ef233c", width=max(2, round(4*scale)))
                elapsed = f"{int(t)//60:02d}:{t%60:04.1f} / {int(full_duration)//60:02d}:{full_duration%60:04.1f}"
                draw.text((width/2, height*.88), elapsed, font=normal, fill="#555555", anchor="mm")
                return np.asarray(image)

            local_mp4 = work / "playalong.mp4"
            video = VideoClip(frame_function=frame, duration=duration).with_audio(audio.subclipped(0, duration))
            try:
                video.write_videofile(str(local_mp4), fps=fps, codec="libx264", audio_codec="aac",
                                      preset="fast", pixel_format="yuv420p",
                                      temp_audiofile=str(work / "sound.m4a"), logger="bar")
                output_path.parent.mkdir(parents=True, exist_ok=True)
                shutil.copyfile(local_mp4, output_path)
            finally:
                video.close()
    print("Saved:", output_path)
    return output_path


## 5. Generate the full song and optional evaluation MP4
The standard MP4 is always generated in full by default. Set `generate_evaluation_video = True` for a second MP4 with correctness colors and accuracy. Set `ground_truth_override` if the reference CSV is stored elsewhere. Otherwise it finds `{song_id}*_ground_truth.csv` within `aam_cleaned_csv`.

`preview_seconds` is **None** by default. Only change it to a number if you explicitly want a short preview. Existing output filenames are replaced when rerendering.


In [10]:
preview_seconds = None  # Full-length export. Optional: 10 for a quick preview.
generate_evaluation_video = True  # True = also create a separate evaluation MP4.
ground_truth_override = None  # Or Path("/content/drive/MyDrive/.../0174_ground_truth.csv")

# Resolve the reference before rendering so missing files are reported immediately.
reference_path = None
if generate_evaluation_video:
    if ground_truth_override:
        reference_path = Path(ground_truth_override)
    else:
        matches = list((project_path / "aam_cleaned_csv").rglob(f"{song_id}*_ground_truth.csv"))
        if len(matches) != 1:
            raise ValueError(f"Expected one ground-truth CSV for {song_id}, found {matches}. Set ground_truth_override.")
        reference_path = matches[0]
    assert reference_path.is_file(), f"Missing reference: {reference_path}"
    print("Reference:", reference_path)

suffix = "_preview" if preview_seconds else ""
output_path = output_folder / prediction_folder.name / f"{song_id}_playalong{suffix}.mp4"
video_path = make_playalong(audio_path, csv_path, output_path, preview_seconds=preview_seconds)
display(Video(str(video_path), embed=True, width=960))

if generate_evaluation_video:
    evaluation_output = output_path.with_name(f"{song_id}_playalong_evaluation{suffix}.mp4")
    evaluation_video_path = make_playalong(audio_path, csv_path, evaluation_output,
                                         preview_seconds=preview_seconds, ground_truth_path=reference_path)
    display(Video(str(evaluation_video_path), embed=True, width=960))


Reference: /content/drive/MyDrive/Femman/DT2470 Music Informatics/DT2470 Project/full_data/aam_cleaned_csv/0057_ground_truth.csv
MoviePy - Building video /tmp/playalong_h0pud1zl/playalong.mp4.
MoviePy - Writing audio in /tmp/playalong_h0pud1zl/sound.m4a


MoviePy - Done.
MoviePy - Writing video /tmp/playalong_h0pud1zl/playalong.mp4



MoviePy - Done !
MoviePy - video ready /tmp/playalong_h0pud1zl/playalong.mp4
Saved: /content/drive/MyDrive/Femman/DT2470 Music Informatics/DT2470 Project/full_data/playalong_videos/4f12560a1fd5a9f6/0057_playalong.mp4


MoviePy - Building video /tmp/playalong_uv_z6n1e/playalong.mp4.
MoviePy - Writing audio in /tmp/playalong_uv_z6n1e/sound.m4a


MoviePy - Done.
MoviePy - Writing video /tmp/playalong_uv_z6n1e/playalong.mp4



MoviePy - Done !
MoviePy - video ready /tmp/playalong_uv_z6n1e/playalong.mp4
Saved: /content/drive/MyDrive/Femman/DT2470 Music Informatics/DT2470 Project/full_data/playalong_videos/4f12560a1fd5a9f6/0057_playalong_evaluation.mp4


### Optional: download the generated MP4
The MP4 is already saved in Drive. This extra cell downloads a copy to your computer. Large MP4s may take time to embed in the notebook; they can also be played directly from Drive.


In [6]:
from google.colab import files
files.download(str(video_path))


<IPython.core.display.Javascript object>

<IPython.core.display.Javascript object>